In [2]:
import pandas as pd
import numpy as np
import plotly.graph_objects as go
import plotly.figure_factory as ff
from plotly.subplots import make_subplots

In [17]:
df = pd.read_csv("./mouse_data.csv")
femtemp = df.iloc[:, :13]
femact = df.iloc[:, 13:26]
maletemp = df.iloc[:, 26:39]
df.columns

Index(['f1_temp', 'f2_temp', 'f3_temp', 'f4_temp', 'f5_temp', 'f6_temp',
       'f7_temp', 'f8_temp', 'f9_temp', 'f10_temp', 'f11_temp', 'f12_temp',
       'f13_temp', 'f1_act', 'f2_act', 'f3_act', 'f4_act', 'f5_act', 'f6_act',
       'f7_act', 'f8_act', 'f9_act', 'f10_act', 'f11_act', 'f12_act',
       'f13_act', 'm1_temp', 'm2_temp', 'm3_temp', 'm4_temp', 'm5_temp',
       'm6_temp', 'm7_temp', 'm8_temp', 'm9_temp', 'm10_temp', 'm11_temp',
       'm12_temp', 'm13_temp', 'm1_act', 'm2_act', 'm3_act', 'm4_act',
       'm5_act', 'm6_act', 'm7_act', 'm8_act', 'm9_act', 'm10_act', 'm11_act',
       'm12_act', 'm13_act'],
      dtype='object')

In [18]:
female_data = femact.stack().dropna()
male_data = maleact.stack().dropna()

hist_data = [female_data, male_data]
group_labels = ['Female', 'Male']

fig = ff.create_distplot(
    hist_data,
    group_labels,
    bin_size=(max(female_data.max(), male_data.max()) - min(female_data.min(), male_data.min())) / 20,
    show_hist=True,
    show_rug=False
)

fig.update_layout(
    xaxis_title='Activity',
    yaxis_title='Density',
    title='Histogram and KDE of Male vs Female Activity',
    barmode='group'
)

fig.show()

In [20]:
femtemp['Average'] = femtemp.mean(axis=1)
maletemp['Average'] = maletemp.mean(axis=1)

fig = make_subplots(rows=2, cols=1, shared_xaxes=True, subplot_titles=('Female Temperature', 'Male Temperature'))

for col in femtemp.columns[:-1]:
    fig.add_trace(go.Scatter(x=femtemp.index/60/24, y=femtemp[col], name=col, line=dict(width=1), showlegend=False), row=1, col=1)
fig.add_trace(go.Scatter(x=femtemp.index/60/24, y=femtemp['Average'], name='Female Average', line=dict(color='blue', width=2, dash='dash')), row=1, col=1)

clean_maletemp = maletemp.drop(columns=['m5_temp', 'm11_temp'])
for col in clean_maletemp.columns[:-1]:
    fig.add_trace(go.Scatter(x=clean_maletemp.index/60/24, y=clean_maletemp[col], name=col, line=dict(width=1), showlegend=False), row=2, col=1)
fig.add_trace(go.Scatter(x=clean_maletemp.index/60/24, y=clean_maletemp['Average'], name='Male Average', line=dict(color='black', width=2, dash='dash')), row=2, col=1)

fig.update_layout(
    xaxis_title='Day',
    yaxis_title='Temperature',
    height=700,
    showlegend=True,
    title={
        'text': 'Temperature over Time by Sex',
        'xanchor': 'center',
        'x': 0.46,
    }
)

fig.show()

In [21]:
femact['Average'] = femact.mean(axis=1)
maleact['Average'] = maleact.mean(axis=1)

fig = make_subplots(rows=2, cols=1, shared_xaxes=True, subplot_titles=('Female Activity', 'Male Activity'))

for col in femact.columns[:-1]:
    fig.add_trace(go.Scatter(x=femact.index/60/24, y=femact[col], name=col, line=dict(width=1), showlegend=False), row=1, col=1)
fig.add_trace(go.Scatter(x=femact.index/60/24, y=femact['Average'], name='Female Average', line=dict(color='blue', width=2, dash='dash')), row=1, col=1)

for col in maleact.columns[:-1]:
    fig.add_trace(go.Scatter(x=maleact.index/60/24, y=maleact[col], name=col, line=dict(width=1), showlegend=False), row=2, col=1)
fig.add_trace(go.Scatter(x=maleact.index/60/24, y=maleact['Average'], name='Male Average', line=dict(color='black', width=2, dash='dash')), row=2, col=1)

fig.update_layout(
    xaxis_title='Day',
    yaxis_title='Activity',
    height=700,
    showlegend=True,
    title={
        'text': 'Activity over Time by Sex',
        'xanchor': 'center',
        'x': 0.46,
    }
)

fig.show()

In [29]:
agg = pd.DataFrame()

In [22]:
import plotly.graph_objects as go
import pandas as pd
from plotly.subplots import make_subplots

# Function to convert oklab to RGB
def oklab_to_rgb(l, a, b):
    # Constants for oklab to rgb conversion
    M = [
        [0.4002, 0.7075, -0.0808],
        [-0.2263, 1.1653, 0.0457],
        [0.0000, 0.0000, 0.9182]
    ]
    rgb = [l, a, b]
    rgb = [sum(M[i][j] * rgb[j] for j in range(3)) for i in range(3)]
    rgb = [max(0, min(1, x)) for x in rgb]
    return rgb

# Function to adjust brightness of an oklab color
def adjust_brightness_oklab(oklab_color, factor):
    l, a, b = oklab_color
    l = max(0, min(1, l * factor))  # Keep within valid range
    return l, a, b

# Function to plot the data with varying shades of oklab color
def avg_day(df, std=1, base_oklab=(0.5, 0, 0), title='', fig=None, row=1, col=1):
    df['Average'] = df.mean(axis=1)
    df['Std'] = df.std(axis=1)

    minutes_per_day = 60 * 24
    days = len(df) // minutes_per_day

    avg_per_min = df['Average'].values.reshape(days, minutes_per_day).mean(axis=0)
    std_per_min = df['Std'].values.reshape(days, minutes_per_day).mean(axis=0)
    time = pd.Series(range(minutes_per_day)) / 60

    xaxis = f'x{col}' if col > 1 else 'x1'
    yaxis = f'y{col}' if col > 1 else 'y1'

    if fig is None:
        fig = go.Figure()

    for i, n in enumerate([4, 2, 1]):
        adjusted_oklab = adjust_brightness_oklab(base_oklab, factor=1 + 0.3 * i)
        r, g, b = oklab_to_rgb(*adjusted_oklab)
        color = f'rgba({int(r * 255)}, {int(g * 255)}, {int(b * 255)}, 0.2)'

        upper = avg_per_min + std_per_min * n * std
        lower = avg_per_min - std_per_min * n * std

        fig.add_trace(go.Scatter(
            x=time, 
            y=upper, 
            line=dict(color='rgba(0,0,0,0)'), 
            showlegend=False,
            xaxis=xaxis,
            yaxis=yaxis
        ))
        fig.add_trace(go.Scatter(
            x=time, 
            y=lower, 
            line=dict(color='rgba(0,0,0,0)'), 
            fill='tonexty',
            fillcolor=color,
            showlegend=False,
            xaxis=xaxis,
            yaxis=yaxis
        ))

    adjusted_oklab_avg = adjust_brightness_oklab(base_oklab, factor=1.3)  
    r_avg, g_avg, b_avg = oklab_to_rgb(*adjusted_oklab_avg)
    avg_color = f'rgba({int(r_avg * 255)}, {int(g_avg * 255)}, {int(b_avg * 255)}, 1)'

    fig.add_trace(go.Scatter(
        x=time, 
        y=avg_per_min, 
        name='Average', 
        line=dict(color=avg_color, width=2),
        xaxis=xaxis,
        yaxis=yaxis
    ))

    fig.add_vline(x=12, line=dict(color='black', dash='dash'), annotation_text="Lights On", annotation_position="top right", row='all', col='all')
    fig.add_vline(x=0, line=dict(color='black', dash='dash'), annotation_text="Lights Off", annotation_position="top right", row='all', col='all')

    fig.update_layout(
    xaxis2_title='Time (Hours)',
    yaxis2_title='Temperature',
        title=title,
        showlegend=False
    )

    return fig

In [26]:
fig = make_subplots(rows=1, cols=2, subplot_titles=('Male', 'Female'))
avg_day(maletemp, std=0.05, base_oklab=(0.3, 0.2, 270/360), title='Male', fig=fig, row=1, col=1)
avg_day(femtemp, std=0.05, title='Female', fig=fig, row=1, col=2)

fig.update_layout(
    title={'text': 'Temperature Over a Day by Sex', 'x': 0.5, 'xanchor': 'center'},
    xaxis_title='Time (Hours)',
    yaxis_title='Temperature',
    yaxis2=dict(matches='y1'),
    width=1200,
    height=600
)

fig.show()

In [27]:
fig = make_subplots(rows=1, cols=2, subplot_titles=('Male', 'Female'))
avg_day(maleact, std=0.2, base_oklab=(0.3, 0.2, 270/360), title='Male', fig=fig, row=1, col=1)
avg_day(femact, std=0.2, title='Female', fig=fig, row=1, col=2)

fig.update_layout(
    title={'text': 'Activity Over a Day by Sex', 'x': 0.5, 'xanchor': 'center'},
    xaxis_title='Time (Hours)',
    yaxis_title='Activity',
    yaxis2=dict(matches='y1'),
    width=1200,
    height=600
)

fig.show()